# 2025-2026 Teacher Preparation Program Placements
### FS26 CMSE 830
### By: Katie Denzin

#################################################################################################################################################

## Problem, audience & narrative

__Problem:__ *Each year, the MSU Teacher Preparation Program places roughly one thousand students in clinical placements to prepare them to be teachers of records. The amount of placements and the range of experiences that students encounter lead to a large amount of data of interest primarily to the placements coordinators and staff/faculty in TPP. It is also of interest to applicable parties such as our district partners, our accreditor, and the Michigan Department of Education. The placement data was compiled from multiple different sources including internal placement documents, school data from mischooldata.com, and addresses from the NCES database. This data can reveal the populations and characteristics of the K-12 student population that MSU Teacher Candidates encounter as well as reveal patterns and resources for the team that places these students. Interactions with this data and resulting visualizations should reveal valuable insight for the Teacher Prep program and tell the story of the 2025-2026 school year for the teacher candidates.*

__Audience:__ MSU Teacher Preparation Program faculty and staff as well as interested parties such as committees, administrators, and accreditors.

## Data, Data Cleaning, and Preparation

Data Sources: 
- place = student placements compiled by me from MSU TPP internal documents.
- demographics = student counts from mischooldata.com
- addresses = school building addresses from NCES

Important Data Cleaning/Pre-Processing decisions:
- Deidentifying data: I completed this elsewhere as protecting student information is very important to me.
- Building Name: there are many repeats of school building names in the three different files. Matching and making sure all of those are correct took a while and was important to data quality.
- Private Schools: there were two schools that we partnered with that are private and therefore do not have demographic information. These were a small number of placements that I decided to exclude for a complete case analysis.
- <10: for the school counts, there is a measure for "<10" preventing it from being an int column. I replaced these with 9.
- School Building Focused: I reformatted the data to be school building based instead of individual placement based. This makes the analysis a lot easier, cleaner, and avoiding repeats.
- Enrollments: I converted the count of students to percentages using the total enrollment column

In [1]:
# imports
import pandas as pd
import numpy as np
import streamlit as st
import altair as alt
from altair.datasets import data


In [2]:
# read in all three files

place = pd.read_excel("placements.xlsx")
demographics = pd.read_excel("studentcounts2526.xlsx")
addresses = pd.read_excel("addresses.xlsx")

In [3]:
# number of students placed in 25-26
# many students have multiple placements at a time

len(place["Identifier"].unique())

988

In [4]:
# clean demographics
import matplotlib.pyplot as plt

# for the <10 values, I am replacing them with 9.
demographics = demographics.replace("<10", "9")

# convert object columns to ints
demographics['ENGLISH_LANGUAGE_LEARNERS_ENROLLMENT'] = demographics['ENGLISH_LANGUAGE_LEARNERS_ENROLLMENT'].astype(int)
demographics['ECONOMIC_DISADVANTAGED_ENROLLMENT'] = demographics['ECONOMIC_DISADVANTAGED_ENROLLMENT'].astype(int)
demographics['SPECIAL_EDUCATION_ENROLLMENT'] = demographics['SPECIAL_EDUCATION_ENROLLMENT'].astype(int)


In [5]:
# convert columns to percentages of total enrollment
cols = ['AMERICAN_INDIAN_ENROLLMENT', 'ASIAN_ENROLLMENT', 'AFRICAN_AMERICAN_ENROLLMENT', 'HISPANIC_ENROLLMENT', 'HAWAIIAN_ENROLLMENT', 'WHITE_ENROLLMENT', 'TWO_OR_MORE_RACES_ENROLLMENT', 'ECONOMIC_DISADVANTAGED_ENROLLMENT', 'SPECIAL_EDUCATION_ENROLLMENT', 'ENGLISH_LANGUAGE_LEARNERS_ENROLLMENT']

for c in cols:
    demographics[c] = demographics[c]/demographics['TOTAL_ENROLLMENT']



In [6]:
# clean addresses
addresses = addresses[['NAME', 'STREET', 'CITY', 'STATE',
       'ZIP', 'LAT', 'LON']] # trim the dataset
michigan = addresses[addresses["STATE"]=="MI"] # only include schools in Michigan
michigan.rename(columns={"NAME":"BuildingName"}, inplace=True) # rename to merge with the other two files

In [7]:
# merge files together

placements = pd.merge(place, demographics, how="left", on='BuildingName')
placements = pd.merge(placements, michigan, how="left", on='BuildingName')

In [8]:
len(placements["Identifier"].unique())

988

In [9]:
# reformat data to be school based for the map and get building based statistics


# consolidate information such as teams, statuses, students, and semesters grouped by building
by_building = pd.DataFrame(placements.groupby('BuildingName')['Team'].unique())
status = pd.DataFrame(placements.groupby('BuildingName')['Status'].unique())
identifier = pd.DataFrame(placements.groupby('BuildingName')['Identifier'].unique())
semester = pd.DataFrame(placements.groupby('BuildingName')['Semester'].unique())
classes = pd.DataFrame(placements.groupby('BuildingName')['Class'].unique())


# combine into one dataframe
by_building = pd.merge(by_building, status, how = 'left', on='BuildingName')
by_building = pd.merge(by_building, identifier, how = 'left', on='BuildingName')
by_building = pd.merge(by_building, semester, how = 'left', on='BuildingName')
by_building = pd.merge(by_building, classes, how = 'left', on='BuildingName')


# find the unique number of students at each placement
by_building['Placements'] = [len(c) for c in by_building['Identifier']]

# convert all list type columns to strings because altair does NOT like the lists
by_building['TeamStr'] = by_building['Team'].apply(lambda x: ', '.join(map(str, x)))
by_building['StatusStr'] = by_building['Status'].apply(lambda x: ', '.join(map(str, x)))
by_building['SemesterStr'] = by_building['Semester'].apply(lambda x: ', '.join(map(str, x)))
by_building['IdentifierStr'] = by_building['Identifier'].apply(lambda x: ', '.join(map(str, x)))
by_building['Experience'] = by_building['Class'].apply(lambda x: ', '.join(map(str, x)))

# drop list columns
by_building = by_building.drop(columns=['Team', 'Status', 'Semester', 'Identifier', 'Class'])

# add addresses and demographics info
by_building = pd.merge(by_building, demographics, how="left", on='BuildingName')
by_building = pd.merge(by_building, michigan, how="left", on='BuildingName')

In [10]:
# filtering using the strings because altair hates lists. will be used later on

# strings = ['ELEM', 'SEC', 'ESL']
# by_building[np.where(by_building.TeamStr.str.contains('|'.join(strings)),True,False)]

# reference: https://stackoverflow.com/questions/28914078/filter-out-rows-based-on-list-of-strings-in-pandas


In [11]:
# export csv if needed. files will be used in the streamlit app

# placements.to_csv("placements.csv", index = False)
# by_building.to_csv("buildings.csv", index = False)
# demographics.to_csv("demographics_cleaned.csv", index = False)

## EDA and Visualization

__EDA #1:__ *What type of schools and students are teacher candidates gaining experience in before becoming the teacher of record?*


In [12]:
strings = ['ELEM', 'ESL', 'SEC', 'SPED'] # will be multi select 

# change column names so it is prettier on the legend
by_building.rename(columns={'AMERICAN_INDIAN_ENROLLMENT':'American Indian',
                    'AFRICAN_AMERICAN_ENROLLMENT':'African American',
                    'HISPANIC_ENROLLMENT':'Hispanic',
                    'WHITE_ENROLLMENT':'White',
                    'HAWAIIAN_ENROLLMENT':'Hawaiian',
                    'ASIAN_ENROLLMENT':'Asian',
                    'TWO_OR_MORE_RACES_ENROLLMENT':'Two or More Races'}, inplace=True)

#list of columns to pull
race = ['American Indian', 'African American', 'Asian', 'Hawaiian', 'Hispanic', 'White', 'Two or More Races']

# filter based on multi-select
filtered = by_building[np.where(by_building.TeamStr.str.contains('|'.join(strings)),True,False)]

# create the histogram
test = alt.Chart(filtered, title=alt.Title("School Building Demographics", subtitle='Demographic distributions for buildings hosting MSU TPP Teacher Candidates')).transform_fold(
    race,
    as_=['Enrollment', 'Measurement']
).mark_bar(
    opacity=0.5,
    binSpacing=0.1
).encode(
    alt.X('Measurement:Q', title="Percentage Enrollment").bin(maxbins=20).axis(format='%'),
    alt.Y('count()', title='Normalized Percentage').stack("normalize"),
    alt.Color('Enrollment:N')
)

In [13]:
# recreate the above graph with all michigan schools to compare

demo = demographics[demographics["BuildingName"] != "All Buildings"]
demo.rename(columns={'AMERICAN_INDIAN_ENROLLMENT':'American Indian',
                    'AFRICAN_AMERICAN_ENROLLMENT':'African American',
                    'HISPANIC_ENROLLMENT':'Hispanic',
                    'WHITE_ENROLLMENT':'White',
                    'HAWAIIAN_ENROLLMENT':'Hawaiian',
                    'ASIAN_ENROLLMENT':'Asian',
                    'TWO_OR_MORE_RACES_ENROLLMENT':'Two or More Races'}, inplace=True)
all_mi = alt.Chart(demo, title=alt.Title("All Michigan Building Demographics", subtitle=['Demographic distribution for all school buildings in Michigan'])).transform_fold(
    race,
    as_=['Enrollment', 'Measurement']
).mark_bar(
    opacity=0.5,
    binSpacing=0.1
).encode(
    alt.X('Measurement:Q', title="Percentage Enrollment").bin(maxbins=20).axis(format='%'),
    alt.Y('count()', title='Normalized Percentage').stack("normalize"),
    alt.Color('Enrollment:N')
)


In [14]:
# combine into one

alt.concat(test,all_mi)

alt.ConcatChart(...)

In [15]:
# EDA #1 Visual #2

# change column names so it is prettier on the legend
by_building.rename(columns={'ECONOMIC_DISADVANTAGED_ENROLLMENT':'Economically Disadvantaged',
                            'SPECIAL_EDUCATION_ENROLLMENT':'Special Education',
                            'ENGLISH_LANGUAGE_LEARNERS_ENROLLMENT':'English Language Learners'}, inplace=True)

#list of columns to pull
cols_boxplot = ['Economically Disadvantaged', 'Special Education', 'English Language Learners']

# make box plot
tpp = alt.Chart(by_building, title=alt.Title("TPP School Building Enrollments", subtitle="2025-2026 Academic Year")).transform_fold(cols_boxplot, as_=["Measurement", "Percentage"]).mark_boxplot(size=50).encode(
    alt.X("Measurement:N"),
    alt.Y("Percentage:Q", title="Percentage Enrollment"),
    color=alt.Color("Measurement:N", legend=None)
).properties(width=300)

In [16]:
# recreate to compare with all of Michigan

demo = demographics[demographics["BuildingName"] != "All Buildings"]
demo.rename(columns={'ECONOMIC_DISADVANTAGED_ENROLLMENT':'Economically Disadvantaged',
                            'SPECIAL_EDUCATION_ENROLLMENT':'Special Education',
                            'ENGLISH_LANGUAGE_LEARNERS_ENROLLMENT':'English Language Learners'}, inplace=True)

#filter out very small schools that the replacing with 9 method messed up
demo = demo[demo["Economically Disadvantaged"]<1]

#list of columns to pull
cols_mi = ['Economically Disadvantaged', 'Special Education', 'English Language Learners']

# create boxplot
mi = alt.Chart(demo, title=alt.Title("Michigan School Building Enrollments", subtitle="2025-2026 Academic Year")).transform_fold(cols_mi, as_=["Measurement", "Percentage"]).mark_boxplot(size=50).encode(
    alt.X("Measurement:N"),
    alt.Y("Percentage:Q", title="Percentage Enrollment"),
    color=alt.Color("Measurement:N", legend=None)
).properties(width=300)

In [17]:
alt.concat(tpp, mi)

alt.ConcatChart(...)

__EDA #2:__ *Where are MSU TPP Teacher Candidates placed across Michigan?*

In [18]:
# map of placements without the map behind it, easier to zoom in and out but no map/orientation as to where you are
# given that my audience would be pretty familiar with our placements, I do not think that this would be a big deal for them. 

# TODO 3: Create an Altair chart using the FILTERED dataframe.
min_lat = min(by_building["LAT"])
min_lon = min(by_building["LON"])
max_lat = max(by_building["LAT"])
max_lon = max(by_building["LON"])

strings = ['SPED', "ESL", 'SPED', 'SEC'] # will be multi select 


map_filter = by_building[np.where(by_building.TeamStr.str.contains('|'.join(strings)),True,False)]

map_filter.replace(["Intern, Pre-Intern", "Pre-Intern, Intern"], value="Both", inplace=True) # only three colors for each status
cols_rename ={'AMERICAN_INDIAN_ENROLLMENT':'American Indian',
                    'AFRICAN_AMERICAN_ENROLLMENT':'African American',
                    'HISPANIC_ENROLLMENT':'Hispanic',
                    'WHITE_ENROLLMENT':'White',
                    'HAWAIIAN_ENROLLMENT':'Hawaiian',
                    'ASIAN_ENROLLMENT':'Asian',
                    'TWO_OR_MORE_RACES_ENROLLMENT':'Two or More Races', 
                    "StatusStr":"Level(s)", 
                    "TeamStr":"Team(s)",
                    }

map_filter.rename(columns=cols_rename, inplace=True) # changing name for legend beautification

chart = alt.Chart(map_filter).mark_point().encode(
    x=alt.X('LON:Q', title='Longitude').scale(domain=[min_lon-0.2, max_lon+0.2]),
    y=alt.Y('LAT:Q', title='Latitude').scale(domain=[min_lat-0.2, max_lat+0.2]),
    size=alt.StrokeWidth('Placements:N', legend=None),
    color=alt.Color('Level(s):N'),
    tooltip=["BuildingName:N", "STREET:N", "CITY:N", "Placements:N", "Team(s)", "Experience:N", 
                 'American Indian:N', 'African American:N', 'Asian:N', 'Hawaiian:N', 'Hispanic:N', 'White:N', 'Two or More Races:N']
).properties(
    width=600, height=350,
    title='Map of Placements'
).interactive()

chart

alt.Chart(...)

In [19]:
# map with Michigan behind it, but much harder to control and interact with

min_lat = min(by_building["LAT"])
min_lon = min(by_building["LON"])
max_lat = max(by_building["LAT"])
max_lon = max(by_building["LON"])

######
# credit to: joelostblom from GitHub https://github.com/vega/altair/issues/679#issuecomment-3242491931
# accessed 10/18/2026
states = alt.topo_feature(data.us_10m.url, 'states')
# Create bindings for pan/zoom
zoom_bind = alt.binding_range(min=2000, max=50000, step=50, name='Zoom ')
center_lat_bind = alt.binding_range(min=min_lat-1, max=max_lat+1, step=0.1, name='Center Lat ')
center_lon_bind = alt.binding_range(min=min_lon-1, max=max_lon+1, step=0.1, name='Center Lon ')
zoom_param = alt.param(value=3500, bind=zoom_bind)
center_lat_param = alt.param(value=43, bind=center_lat_bind)
center_lon_param = alt.param(value=-85, bind=center_lon_bind)
# Base chart with dynamic projection

base = alt.Chart(states).mark_geoshape(
    fill='lightgray', stroke='white'
).project(
    type='mercator',
    scale=zoom_param,
    center=alt.expr(f'[{center_lon_param.name}, {center_lat_param.name}]')
).add_params(zoom_param, center_lat_param, center_lon_param).interactive()
#####

# filter by selection (team)
strings = ['SPED', "ESL", 'SPED', 'SEC'] # will be multi select 
map_filter = by_building[np.where(by_building.TeamStr.str.contains('|'.join(strings)),True,False)]

# rename and replace certain values for readability in the final map
map_filter.replace(["Intern, Pre-Intern", "Pre-Intern, Intern"], value="Both", inplace=True) # only three colors for each status
cols_rename ={'AMERICAN_INDIAN_ENROLLMENT':'American Indian',
                    'AFRICAN_AMERICAN_ENROLLMENT':'African American',
                    'HISPANIC_ENROLLMENT':'Hispanic',
                    'WHITE_ENROLLMENT':'White',
                    'HAWAIIAN_ENROLLMENT':'Hawaiian',
                    'ASIAN_ENROLLMENT':'Asian',
                    'TWO_OR_MORE_RACES_ENROLLMENT':'Two or More Races', 
                    "StatusStr":"Level(s)", 
                    "TeamStr":"Team(s)",
                    }

map_filter.rename(columns=cols_rename, inplace=True) # changing name for 


# create the map of placements
points = alt.Chart(map_filter, title=alt.Title("Map of Placements", subtitle="2025-2026 Academic Year")).mark_circle().encode(
    longitude=alt.Longitude('LON', type='quantitative'),
    latitude=alt.Latitude('LAT', type='quantitative'),
    size=alt.StrokeWidth('Placements:N', legend=None),
    color=alt.Color('Level(s):N'),
    tooltip=["BuildingName:N", "STREET:N", "CITY:N", "Placements:N", "Team(s)", "Experience:N", 
             'American Indian:N', 'African American:N', 'Asian:N', 'Hawaiian:N', 'Hispanic:N', 'White:N', 'Two or More Races:N']
).project(
    type='mercator',
    scale=zoom_param,
    center=alt.expr(f'[{center_lon_param.name}, {center_lat_param.name}]')
).interactive()

base + points

alt.LayerChart(...)

## Interpretation and Limitations

__Visualization #1__

In [20]:
alt.concat(test,all_mi)

alt.ConcatChart(...)

__Key Takeaways__
- The majority of K-12 Schools that MSU TPP partners with is majority white, with a couple that are majority Hispanic and/or African American.
- Notably, TPP students have the least exposure to students with American Indian heritage compared to the overall Michigan distribution.
- The distribution of demographic enrollment roughly resembles that of the distribution of all of Michigan schools. 
- Filtering by the subject area team can reveal if sub-categories of students also have the same distribution.

__Limitations__
- It would be interesting to filter by status/level if needed.
- The Y-axis can be slighly confusing if someone didn't know what they were looking at.


__Visualization #2__

In [21]:
alt.concat(tpp, mi)

alt.ConcatChart(...)

In [22]:
ed0, ed25, ed50, ed75, ed1 = by_building["Economically Disadvantaged"].quantile([0, 0.25, 0.5, 0.75, 1])
ell0, ell25, ell50, ell75, ell1 = by_building["English Language Learners"].quantile([0, 0.25, 0.5, 0.75, 1])
se0, se25, se50, se75, se1 = by_building["Special Education"].quantile([0, 0.25, 0.5, 0.75, 1])

pd.DataFrame({"Enrollment":["Economically Disadvantaged", "English Language Learners", "Special Education"],
              "Minimum":[ed0, ell0, se0],
              "Q1":[ed25, ell25, se25],
              "Median":[ed50, ell50, se50],
              "Q3":[ed75, ell75, se75],
              "Maximum":[ed1, ell1, se1]})


,Enrollment,Minimum,Q1,Median,Q3,Maximum
0,Economically Disadvantaged,0.036352,0.250712,0.369650,0.600901,0.960133
1,English Language Learners,0.009245,0.025023,0.041667,0.086934,0.741433
2,Special Education,0.009278,0.116067,0.148198,0.179848,1.000000


__Key Takeaways__
- The enrollments of Economically Disadvantaged students, English Language Learners, and Special Education students roughly resemble statewide distributions.
- There are more outliers for ELL and SPED students, so even though the ranges are very similar, the spread of Economically Disadvantaged student enrollment is much wider than the other two. 
- Teacher candidates work closely and often with students and buildings that have a large portion of economically disadvantaged enrollment. 75% of building partners have above 25% E.D. enrollment.
- The maximum enrollment for Special Education enrollment is 100%. This specific data point is the Beekman Center in Lansing which is a specialized school specifically for students with different needs.
- English Language Learners enrollment have the smallest range of enrollments with 75% at less than 8.7% of students in the TPP partner schools.
- TPP Teacher Canidates gain exposure to a lot of students with diverse backgrounds in their placements.

__Limitations__
- The Michigan dataset has a lot of outliers for ELL and SPED enrollment which makes the data a bit messy and hard to report in aggregate.
- The ToolTip is not in the best format, I want to make it a rounded percentage in the future.



__Visualization #3__

In [23]:
base + points

alt.LayerChart(...)

In [24]:
# maximum number of placements
by_building[by_building["Placements"]==by_building["Placements"].max()]

,BuildingName,Placements,TeamStr,StatusStr,SemesterStr,IdentifierStr,Experience,SchoolYear,ISDCode,ISDName,...,Economically Disadvantaged,Special Education,English Language Learners,DEVELOPMENTAL_KINDERGARTEN_ENROLLMENT,STREET,CITY,STATE,ZIP,LAT,LON
111,North Aurelius Elementary School,106,"ELEM, ESL, SPED","Pre-Intern, Intern","SS26, FS25/SS26, FS25","559731, 510583, 219083, 343570, 761271, 461801...","TE 301, Elementary Internship, ITP, TE 342, CE...",25 - 26 School Year,33.0,Ingham ISD,...,0.229917,0.144044,0.024931,9,115 N AURELIUS RD,MASON,MI,48854.0,42.5855,-84.5238


In [69]:
singles = len(by_building[by_building["Placements"]==1])
print("Number of buildings with only 1 teacher candidate: ", singles)
perct = np.round(singles/len(by_building)*100, decimals=1)
print("Percentage: ", perct, "%")


Number of buildings with only 1 teacher candidate:  66
Percentage:  35.7 %


__Key Takeaways__
- Most placements are focused in the Lansing area. Intern-level placements are more spread out. There are a fair number of schools in the Lansing area that host only pre-interns or only interns which is interesting in terms of the type of partnerships we have with those schools.
- The school we had the most placements at was North Aurelius Elementary school with 106 placements across Elementary, English as a Second Language, and Special Education students and five different field experiences.
- Most schools (64.3%) have more than one placement, meaning teacher candidates are mostly placed together. There were 66 schools (35.7%) that hosted only one teacher candidate. It is a goal of the program to try and place students together so this is notable for this analysis.
- Filtering by team shows where different disciplines are placed across the state and where certain placement coordinators have established relationships with K-12 partners.

__Limitations__
- The map is not very user-friendly. There is not a lot of built in map features for Altair.
- The ToolTip information is a bit ugly and should be formatted differently in the future.
- Some of the points are a but close together and hard to distinguish, but I think the visual effect of the circle sizes is worth it.

## Streamlit

link: https://cmse830-midterm-denzin.streamlit.app/


To run streamlit locally, uncomment the below three cells:

In [54]:
# start streamlit
# reference: HW #3

# import subprocess, sys, time

# if "streamlit_process" in globals() and streamlit_process.poll() is None:
#     streamlit_process.terminate()
#     try:
#         streamlit_process.wait(timeout=5)
#     except subprocess.TimeoutExpired:
#         streamlit_process.kill()

# streamlit_process = subprocess.Popen(
#     [sys.executable, "-m", "streamlit", "run", "midterm.py",
#      "--server.headless=true", "--server.port=8501",
#      "--browser.gatherUsageStats=false"],
#     stdout=subprocess.DEVNULL, stderr=subprocess.STDOUT
# )
# time.sleep(3)

# if streamlit_process.poll() is None:
#     print("Streamlit is running. Open http://localhost:8501")
# else:
#     print("Streamlit did not stay running. Ask the instructor or TA for help.")

In [53]:
# %%writefile midterm.py
# import pandas as pd
# import numpy as np
# import streamlit as st
# import altair as alt
# from vega_datasets import data
# from altair.datasets import data


# # set title
# st.set_page_config(page_title="MSU TPP Placements", layout="wide")
# st.title("2025-2026 Teacher Preparation Program Placements")

# # read in files
# by_building = pd.read_csv("buildings.csv")
# demographics = pd.read_csv("demographics_cleaned.csv")

# # intro
# st.write("Each year, the MSU Teacher Preparation Program places nearly one thousand students in clinical placements to prepare them to be teachers of records. The amount of placements and the range of experiences that students encounter lead to a large amount of data of interest primarily to the placements coordinators and staff/faculty in TPP. It is also of interest to applicable parties such as our district partners, our accreditor, and the Michigan Department of Education. The placement data was compiled from multiple different sources including internal placement documents, school data from mischooldata.com, and addresses from the NCES database. This data can reveal the populations and characteristics of the K-12 student population that MSU Teacher Candidates encounter as well as reveal patterns and resources for the team that places these students. Interactions with this data and resulting visualizations should reveal valuable insight for the Teacher Prep program and tell the story of the 2025-2026 school year for the teacher candidates.\n\n")
# st.write(" \n")

# # data
# st.write("*The Data*")
# st.write("The following visualizations combine three data sources:")
# st.write("- student placements compiled from MSU TPP internal documents.")
# st.write("- student enrollment counts from mischooldata.com.")
# st.write("- school building addresses from NCES.")
# st.write(" \n")


# ### visual number one ######################################################################################################################



# st.write("_Placement School Demographics_")
# st.write("The following visualization answers the following questions: What are the demographics of the schools that TPP teacher candidates are placed at? How to TPP school partners compare to overall Michigan demographics?\n\n")
# st.write("Note: ELEM = Elementary, ESL = English as a Second Language, SEC = Secondary, and SPED = Special Education")
# # filter results based on choices
# teams = ['ELEM', 'ESL', 'SEC', 'SPED']
# team_filter1 = st.multiselect("Team", teams, default = teams)
# filtered = by_building[np.where(by_building.TeamStr.str.contains('|'.join(team_filter1)),True,False)]


# # change column names so it is prettier on the legend
# filtered.rename(columns={'AMERICAN_INDIAN_ENROLLMENT':'American Indian',
#                     'AFRICAN_AMERICAN_ENROLLMENT':'African American',
#                     'HISPANIC_ENROLLMENT':'Hispanic',
#                     'WHITE_ENROLLMENT':'White',
#                     'HAWAIIAN_ENROLLMENT':'Hawaiian',
#                     'ASIAN_ENROLLMENT':'Asian',
#                     'TWO_OR_MORE_RACES_ENROLLMENT':'Two or More Races'}, inplace=True)
# #list of columns to pull
# race = ['American Indian', 'African American', 'Asian', 'Hawaiian', 'Hispanic', 'White', 'Two or More Races']

# # custom colors
# colors = ["#008208", "#7BBD00", "#49CFA5", "#578800", "#42FF4F", "#0B9A6D", "#CCFA7D"]

# # create the histograms
# tpp_hist = alt.Chart(filtered, title=alt.Title("School Building Demographics", subtitle='Demographic distributions for buildings hosting MSU TPP Teacher Candidates')).transform_fold(
#     race,
#     as_=['Enrollment', 'Measurement']
# ).mark_bar(
#     opacity=0.5,
#     binSpacing=0
# ).encode(
#     alt.X('Measurement:Q', title="Percentage Enrollment").bin(maxbins=20).axis(format='%'),
#     alt.Y('count()', title='Percentage of Schools').stack("normalize"),
#     alt.Color('Enrollment:N').scale(domain=race, range=colors)
# )

# demo = demographics[demographics["BuildingName"] != "All Buildings"]
# demo.rename(columns={'AMERICAN_INDIAN_ENROLLMENT':'American Indian',
#                     'AFRICAN_AMERICAN_ENROLLMENT':'African American',
#                     'HISPANIC_ENROLLMENT':'Hispanic',
#                     'WHITE_ENROLLMENT':'White',
#                     'HAWAIIAN_ENROLLMENT':'Hawaiian',
#                     'ASIAN_ENROLLMENT':'Asian',
#                     'TWO_OR_MORE_RACES_ENROLLMENT':'Two or More Races'}, inplace=True)
# mi_hist = alt.Chart(demo, title=alt.Title("All Michigan Building Demographics", subtitle=['Demographic distribution for all school buildings in Michigan'])).transform_fold(
#     race,
#     as_=['Enrollment', 'Measurement']
# ).mark_bar(
#     opacity=0.5,
#     binSpacing=0
# ).encode(
#     alt.X('Measurement:Q', title="Percentage Enrollment").bin(maxbins=20).axis(format='%'),
#     alt.Y('count()', title='Percentage of Schools').stack("normalize"),
#     alt.Color('Enrollment:N').scale(domain=race, range=colors)
# )

# # final visual 
# visual1 = tpp_hist | mi_hist

# st.altair_chart(visual1, use_container_width=False)

# # analysis/comments



# ### visual number two ######################################################################################################################

# st.write("\n")
# st.write("_Placement School Enrollments_")
# st.write("The following visualization answers the following questions: What are the student enrollments of the schools that TPP teacher candidates are placed at? How to TPP school partners compare to overall Michigan demographics?\n\n")


# # filter results based on choices
# teams2 = ['ELEM', 'ESL', 'SEC', 'SPED']
# team_filter2 = st.multiselect("Team(s)", teams2, default = teams2)
# filtered = by_building[np.where(by_building.TeamStr.str.contains('|'.join(team_filter2)),True,False)]

# # custom colors
# colors = ["#008208", "#7BBD00", "#0B9A6D"]

# # change column names so it is prettier on the legend
# filtered.rename(columns={'ECONOMIC_DISADVANTAGED_ENROLLMENT':'Economically Disadvantaged',
#                             'SPECIAL_EDUCATION_ENROLLMENT':'Special Education',
#                             'ENGLISH_LANGUAGE_LEARNERS_ENROLLMENT':'English Language Learners'}, inplace=True)

# #list of columns to pull
# cols_boxplot = ['Economically Disadvantaged', 'Special Education', 'English Language Learners']

# tpp_box = alt.Chart(filtered, title=alt.Title("TPP School Building Enrollments", subtitle="2025-2026 Academic Year")).transform_fold(cols_boxplot, as_=["Measurement", "Percentage"]).mark_boxplot(size=50).encode(
#     alt.X("Measurement:N", axis=alt.Axis(labels=False)),
#     alt.Y("Percentage:Q", title="Percentage Enrollment"),
#     color=alt.Color("Measurement:N").scale(domain=cols_boxplot, range=colors)
# ).properties(width=300)

# # clean up demographics data set first
# demo = demographics[demographics["BuildingName"] != "All Buildings"]
# demo.rename(columns={'ECONOMIC_DISADVANTAGED_ENROLLMENT':'Economically Disadvantaged',
#                             'SPECIAL_EDUCATION_ENROLLMENT':'Special Education',
#                             'ENGLISH_LANGUAGE_LEARNERS_ENROLLMENT':'English Language Learners'}, inplace=True)

# demo = demo[demo["Economically Disadvantaged"]<1]

# #list of columns to pull
# cols_mi = ['Economically Disadvantaged', 'Special Education', 'English Language Learners']

# mi_box = alt.Chart(demo, title=alt.Title("Michigan School Building Enrollments", subtitle="2025-2026 Academic Year")).transform_fold(cols_mi, as_=["Measurement", "Percentage"]).mark_boxplot(size=50).encode(
#     alt.X("Measurement:N", axis=alt.Axis(labels=False)),
#     alt.Y("Percentage:Q", title="Percentage Enrollment"),
#     color=alt.Color("Measurement:N")
# ).properties(width=300)

# # final visual 
# visual2 = tpp_box | mi_box

# st.altair_chart(visual2, use_container_width=True)

# # analysis/comments


# ### visual number three ######################################################################################################################

# st.write("\n")
# st.write("_Map of Placements_")
# st.write("The following visualization answers the following questions: Where are students placed across Michigan? And at what quantity?\n\n")


# min_lat = min(by_building["LAT"])
# min_lon = min(by_building["LON"])
# max_lat = max(by_building["LAT"])
# max_lon = max(by_building["LON"])

# strings = ['SPED', "ESL", 'ELEM', 'SEC'] # multi select 
# team_filter3 = st.multiselect("Team(s) (map)", strings, default = strings)
# map_filter = by_building[np.where(by_building.TeamStr.str.contains('|'.join(team_filter3)),True,False)]


# map_filter.replace(["Intern, Pre-Intern", "Pre-Intern, Intern"], value="Both", inplace=True) # only three colors for each status
# cols_rename ={'AMERICAN_INDIAN_ENROLLMENT':'American Indian',
#                     'AFRICAN_AMERICAN_ENROLLMENT':'African American',
#                     'HISPANIC_ENROLLMENT':'Hispanic',
#                     'WHITE_ENROLLMENT':'White',
#                     'HAWAIIAN_ENROLLMENT':'Hawaiian',
#                     'ASIAN_ENROLLMENT':'Asian',
#                     'TWO_OR_MORE_RACES_ENROLLMENT':'Two or More Races', 
#                     "StatusStr":"Level(s)", 
#                     "TeamStr":"Team(s)",
#                     }

# map_filter.rename(columns=cols_rename, inplace=True) # changing name for 

# # custom colors
# domain = ["Pre-Intern", "Intern", "Both"]
# colors = ["#008208", "#7BBD00", "#0B9A6D"]

# chart = alt.Chart(map_filter).mark_point().encode(
#     x=alt.X('LON:Q', title='Longitude').scale(domain=[min_lon-0.2, max_lon+0.2]),
#     y=alt.Y('LAT:Q', title='Latitude').scale(domain=[min_lat-0.2, max_lat+0.2]),
#     size=alt.StrokeWidth('Placements:N', legend=None),
#     color=alt.Color('Level(s):N').scale(domain=domain, range=colors),
#     tooltip=["BuildingName:N", "STREET:N", "CITY:N", "Placements:N", "Team(s)", "Experience:N", 
#                  'American Indian:N', 'African American:N', 'Asian:N', 'Hawaiian:N', 'Hispanic:N', 'White:N', 'Two or More Races:N']
# ).properties(
#     width=600, height=350,
#     title='Map of Placements'
# ).interactive()

# st.altair_chart(chart, use_container_width=True)




# # filter by selection (team)
# strings = ['SPED', "ESL", 'ELEM', 'SEC'] # multi select 
# team_filter3 = st.multiselect("Team(s) (map)", strings, default = strings)
# map_filter = by_building[np.where(by_building.TeamStr.str.contains('|'.join(team_filter3)),True,False)]

# # rename and replace certain values for readability in the final map
# map_filter.replace(["Intern, Pre-Intern", "Pre-Intern, Intern"], value="Both", inplace=True) # only three colors for each status
# cols_rename ={'AMERICAN_INDIAN_ENROLLMENT':'American Indian',
#                     'AFRICAN_AMERICAN_ENROLLMENT':'African American',
#                     'HISPANIC_ENROLLMENT':'Hispanic',
#                     'WHITE_ENROLLMENT':'White',
#                     'HAWAIIAN_ENROLLMENT':'Hawaiian',
#                     'ASIAN_ENROLLMENT':'Asian',
#                     'TWO_OR_MORE_RACES_ENROLLMENT':'Two or More Races', 
#                     "StatusStr":"Level(s)", 
#                     "TeamStr":"Team(s)",
#                     }

# map_filter.rename(columns=cols_rename, inplace=True) # changing name of columns

# # find minimum and max of the coordinates
# min_lat = min(by_building["LAT"])
# min_lon = min(by_building["LON"])
# max_lat = max(by_building["LAT"])
# max_lon = max(by_building["LON"])

# # create the map background 

# ######
# # credit to: joelostblom from GitHub https://github.com/vega/altair/issues/679#issuecomment-3242491931
# # accessed 10/18/2026
# states = alt.topo_feature(data.us_10m.url, 'states')
# # Create bindings for pan/zoom
# zoom_bind = alt.binding_range(min=2000, max=50000, step=50, name='Zoom ')
# center_lat_bind = alt.binding_range(min=min_lat-1, max=max_lat+1, step=0.1, name='Center Lat ')
# center_lon_bind = alt.binding_range(min=min_lon-1, max=max_lon+1, step=0.1, name='Center Lon ')
# zoom_param = alt.param(value=3500, bind=zoom_bind)
# center_lat_param = alt.param(value=43, bind=center_lat_bind)
# center_lon_param = alt.param(value=-85, bind=center_lon_bind)
# # Base chart with dynamic projection

# base = alt.Chart(states).mark_geoshape(
#     fill='lightgray', stroke='white'
# ).project(
#     type='mercator',
#     scale=zoom_param,
#     center=alt.expr(f'[{center_lon_param.name}, {center_lat_param.name}]')
# ).add_params(zoom_param, center_lat_param, center_lon_param)
# #####



# # create the map of placements
# points = alt.Chart(map_filter, title=alt.Title("Map of Placements", subtitle="2025-2026 Academic Year")).mark_circle().encode(
#     longitude=alt.Longitude('LON', type='quantitative'),
#     latitude=alt.Latitude('LAT', type='quantitative'),
#     size=alt.StrokeWidth('Placements:N', legend=None),
#     color=alt.Color('Level(s):N'),
#     tooltip=["BuildingName:N", "STREET:N", "CITY:N", "Placements:N", "Team(s)", "Experience:N", 
#              'American Indian:N', 'African American:N', 'Asian:N', 'Hawaiian:N', 'Hispanic:N', 'White:N', 'Two or More Races:N']
# ).project(
#     type='mercator',
#     scale=zoom_param,
#     center=alt.expr(f'[{center_lon_param.name}, {center_lat_param.name}]')
# )

# visual3 = base + points

# st.altair_chart(visual3, use_container_width=True)
# st.write(visual3)


In [52]:
# if "streamlit_process" in globals() and streamlit_process.poll() is None:
#     streamlit_process.terminate()
#     try:
#         streamlit_process.wait(timeout=5)
#     except subprocess.TimeoutExpired:
#         streamlit_process.kill()
#     print("Streamlit stopped.")
# else:
#     print("No Streamlit process started by this notebook is currently running.")

## GitHub

Repository here: https://github.com/kdenzin/CMSE830-Midterm

## AI Disclosure

No AI was directly used in the creation and work of this project.

Please see references directly embedded in the code chunks when relevant.